script to experiment with data from SCE PSPS report figures and tables as provided in the geodatabase files


 

In [9]:
# Ensure OCR dependency exists in current kernel
import importlib.util
import subprocess
import sys

if importlib.util.find_spec('rapidocr_onnxruntime') is None:
    print('Installing rapidocr_onnxruntime into active kernel...')
    subprocess.check_call([sys.executable, '-m', 'pip', 'install', 'rapidocr_onnxruntime'])
else:
    print('rapidocr_onnxruntime already installed')

rapidocr_onnxruntime already installed


In [10]:
import pkgutil
mods = [m.name for m in pkgutil.iter_modules() if 'rapidocr' in m.name.lower() or 'onnx' in m.name.lower()]
print('matching modules:', mods[:100])

matching modules: ['onnxruntime', 'rapidocr_onnxruntime']


In [11]:
from pathlib import Path
import pandas as pd

gdb_path = Path('~/Downloads/PSPS_05172026_event_data.gdb').expanduser()
print({'gdb_exists': gdb_path.exists(), 'gdb_path': str(gdb_path)})

import geopandas as gpd

layers = gpd.list_layers(gdb_path)
print({'layer_count': int(len(layers))})
display(layers)

layer_summaries = []
for layer_name in layers['name'].tolist():
    gdf = gpd.read_file(gdb_path, layer=layer_name)
    geom_type = None if gdf.geometry.isna().all() else ', '.join(sorted(gdf.geometry.geom_type.dropna().unique().tolist()))
    layer_summaries.append({
        'layer': layer_name,
        'rows': int(len(gdf)),
        'columns': int(len(gdf.columns)),
        'crs': str(gdf.crs),
        'geometry_types': geom_type,
        'sample_columns': ', '.join(gdf.columns[:10]),
    })

layer_summary_df = pd.DataFrame(layer_summaries).sort_values(['rows', 'layer'], ascending=[False, True])
display(layer_summary_df)

sample_preview = {}
for layer_name in layers['name'].tolist()[: min(3, len(layers))]:
    gdf = gpd.read_file(gdb_path, layer=layer_name)
    sample_preview[layer_name] = gdf.head(5).drop(columns='geometry', errors='ignore')

for k, v in sample_preview.items():
    print(f'--- {k} (first 5 rows, non-geometry cols) ---')
    display(v)


{'gdb_exists': True, 'gdb_path': '/Users/ryanmc/Downloads/PSPS_05172026_event_data.gdb'}
{'layer_count': 3}


,name,geometry_type
0,PSPS_05172026_damage_or_hazard,Point
1,PSPS_05172025_event_area,MultiPolygon
2,PSPS_05172026DeEnergizedAreas,MultiPolygon


,layer,rows,columns,crs,geometry_types,sample_columns
2,PSPS_05172026DeEnergizedAreas,15,19,EPSG:3857,MultiPolygon,"Event_Name, Time_Place, Circuit_Name, DeEnergi..."
0,PSPS_05172026_damage_or_hazard,4,10,EPSG:3857,Point,"CircuitName, County, StructureIdentifier, HFTD..."
1,PSPS_05172025_event_area,1,10,EPSG:3857,MultiPolygon,"Event_Name, First_Date_of_POC, IOU, DeEnergiza..."


--- PSPS_05172026_damage_or_hazard (first 5 rows, non-geometry cols) ---


,CircuitName,County,StructureIdentifier,HFTD,Damage_or_Hazard,Type_of_Damage_or_Hazard,Description_of_Damage_or_Hazard,Latitude,Longitude
0,Montecello 1101,Napa,103928743.0,Tier 2,Hazard,Foreign object,Other - ballon on line,38.668747,-122.198539
1,Westley 1101,San Joaquin,103370873.0,Non-HFTD,Damage,Wind related,Other – ground wire detached from pole,37.575355,-121.358224
2,Maxwell 1105,Colusa,101617522.0,Non-HFTD,Damage,Wind related,Broken crossarm,39.227977,-122.359815
3,Glenn 1101,Glenn,100369467.0,Non-HFTD,Damage,Wind related,Broken insulator,39.794745,-122.299308


--- PSPS_05172025_event_area (first 5 rows, non-geometry cols) ---


,Event_Name,First_Date_of_POC,IOU,DeEnergization_Start_Date,Full_Restoration_Date,Customers_DeEnergized,DeEnergization,SHAPE_Length,SHAPE_Area
0,PSPS Event 05.17.2026,05/17/26,PG&E,05/17/26,05/18/26,4583,Yes,3.912880e+06,1.913145e+09


--- PSPS_05172026DeEnergizedAreas (first 5 rows, non-geometry cols) ---


,Event_Name,Time_Place,Circuit_Name,DeEnergization_Date_and_Time,AllClear_Date_and_Time,Restoration_Date_and_Time,County,HFTD,Total_Customers,Residential_Customers,Commercial_Industrial_Customers,Medical_Baseline_Customers,AFN_other_than_MBL_Customers,Other_Customers,Transmission_Customers,Distribution_Customers,SHAPE_Length,SHAPE_Area
0,5172026,TP05_05172026,MONTICELLO 1101,2026-05-17 10:50:00,2026-05-18 08:38:00,2026-05-18 19:59:00,YOLO,Tier 2,8,0,7,0,0,1,0,8,15322.646223,4.580371e+06
1,5172026,TP03_05172026,"DUNNIGAN 1103, CORTINA 1101",2026-05-17 10:51:00,2026-05-18 08:38:00,2026-05-18 11:05:00,COLUSA,"Partially Outside HFTD, Tier 2",31,16,13,0,5,2,0,31,58349.703752,3.007048e+07
2,5172026,TP15_05172026,"CANTUA 1102, COALINGA NO 2 1105, COALINGA NO 2...",2026-05-17 13:45:00,2026-05-18 07:12:00,2026-05-18 12:33:00,FRESNO,Outside HFTD,80,11,43,0,1,26,0,80,211470.756199,1.094022e+08
3,5172026,TP11_05172026,CARBONA 1101,2026-05-17 12:55:00,2026-05-18 07:12:00,2026-05-18 11:14:00,"ALAMEDA, SAN JOAQUIN",Outside HFTD,56,22,14,2,3,20,0,56,63186.848344,6.552454e+07
4,5172026,TP06_05172026,"CALPINE 1144, CALPINE 1146",2026-05-17 13:41:00,2026-05-18 13:14:00,2026-05-18 18:00:00,"LAKE, SONOMA","Tier 2, Tier 3",8,2,6,0,0,0,0,8,39264.395490,1.357552e+07


In [12]:
from pathlib import Path
import geopandas as gpd
import pandas as pd

gdb_path = Path('~/Downloads/PSPS_05172026_event_data.gdb').expanduser()

de = gpd.read_file(gdb_path, layer='PSPS_05172026DeEnergizedAreas')
hz = gpd.read_file(gdb_path, layer='PSPS_05172026_damage_or_hazard')
ev = gpd.read_file(gdb_path, layer='PSPS_05172025_event_area')

summary = {
    'event_area_rows': int(len(ev)),
    'deenergized_rows': int(len(de)),
    'hazard_rows': int(len(hz)),
    'deenergized_total_customers': int(pd.to_numeric(de['Total_Customers'], errors='coerce').fillna(0).sum()),
    'deenergized_distribution_customers': int(pd.to_numeric(de['Distribution_Customers'], errors='coerce').fillna(0).sum()),
    'deenergized_transmission_customers': int(pd.to_numeric(de['Transmission_Customers'], errors='coerce').fillna(0).sum()),
    'deenergized_unique_time_place': int(de['Time_Place'].nunique(dropna=True)),
    'hazard_damage_vs_hazard_counts': hz['Damage_or_Hazard'].value_counts(dropna=False).to_dict(),
    'hazard_counties': sorted(hz['County'].dropna().unique().tolist()),
}

def _split_unique(series):
    vals = []
    for x in series.dropna().astype(str):
        vals.extend([p.strip() for p in x.split(',') if p.strip()])
    return sorted(pd.unique(vals).tolist())

summary['deenergized_unique_counties_split'] = _split_unique(de['County'])
summary['deenergized_unique_circuits_split_count'] = len(_split_unique(de['Circuit_Name']))

print(summary)


{'event_area_rows': 1, 'deenergized_rows': 15, 'hazard_rows': 4, 'deenergized_total_customers': 4583, 'deenergized_distribution_customers': 4583, 'deenergized_transmission_customers': 0, 'deenergized_unique_time_place': 15, 'hazard_damage_vs_hazard_counts': {'Damage': 3, 'Hazard': 1}, 'hazard_counties': ['Colusa', 'Glenn', 'Napa', 'San Joaquin'], 'deenergized_unique_counties_split': ['ALAMEDA', 'COLUSA', 'CONTRA COSTA', 'FRESNO', 'GLENN', 'LAKE', 'MERCED', 'NAPA', 'SAN BENITO', 'SAN JOAQUIN', 'SOLANO', 'SONOMA', 'STANISLAUS', 'TEHAMA', 'YOLO'], 'deenergized_unique_circuits_split_count': 31}


/var/folders/g_/2j33jfhn72j448cr82hzgr0c0002d4/T/ipykernel_38687/2151931002.py:27: FutureWarning: unique with argument that is not not a Series, Index, ExtensionArray, or np.ndarray is deprecated and will raise in a future version.
  return sorted(pd.unique(vals).tolist())
/var/folders/g_/2j33jfhn72j448cr82hzgr0c0002d4/T/ipykernel_38687/2151931002.py:27: FutureWarning: unique with argument that is not not a Series, Index, ExtensionArray, or np.ndarray is deprecated and will raise in a future version.
  return sorted(pd.unique(vals).tolist())


In [13]:
from pathlib import Path

import geopandas as gpd
import pandas as pd
import folium
from IPython.display import display

# Inputs
gdb_path = Path("~/Downloads/PSPS_05172026_event_data.gdb").expanduser()
file_path_powergrid_CEC = Path(
    "/Users/ryanmc/Documents/Conferences/Jack_Eddy_Symposium_2022/dev/physical_grid_data/Transmission_Line_data_CA_CEC/TransmissionLine_CEC.shp"
)

if not gdb_path.exists():
    raise FileNotFoundError(f"Geodatabase not found: {gdb_path}")
if not file_path_powergrid_CEC.exists():
    raise FileNotFoundError(f"CEC grid shapefile not found: {file_path_powergrid_CEC}")


def _json_safe_gdf(gdf):
    out = gdf.copy()
    for col in out.columns:
        if col == "geometry":
            continue
        if pd.api.types.is_datetime64_any_dtype(out[col]):
            out[col] = out[col].dt.strftime("%Y-%m-%d %H:%M:%S")
            continue
        if pd.api.types.is_object_dtype(out[col]):
            out[col] = out[col].map(
                lambda v: v.isoformat() if hasattr(v, "isoformat") and not isinstance(v, str) else v
            )
    return out


# Load data
de_areas = gpd.read_file(gdb_path, layer="PSPS_05172026DeEnergizedAreas").to_crs("EPSG:4326")
de_circuits = de_areas.explode(index_parts=False).copy()
gdf_powergrid_CEC = gpd.read_file(file_path_powergrid_CEC).to_crs("EPSG:4326")

county_candidates = [
    Path("notebooks/_cache/tl_2024_us_county/tl_2024_us_county.shp"),
    Path("_cache/tl_2024_us_county/tl_2024_us_county.shp"),
    Path.cwd() / "notebooks/_cache/tl_2024_us_county/tl_2024_us_county.shp",
    Path.cwd() / "_cache/tl_2024_us_county/tl_2024_us_county.shp",
]
county_shp = next((p for p in county_candidates if p.exists()), None)
if county_shp is None:
    raise FileNotFoundError("County shapefile not found.")

counties = gpd.read_file(county_shp)
counties["STATEFP"] = counties["STATEFP"].astype(str).str.zfill(2)
counties_ca = counties[counties["STATEFP"] == "06"].to_crs("EPSG:4326").copy()

# Extents
minx, miny, maxx, maxy = de_areas.total_bounds
center_lat = float((miny + maxy) / 2)
center_lon = float((minx + maxx) / 2)
ca_minx, ca_miny, ca_maxx, ca_maxy = counties_ca.total_bounds
ca_bounds = [[float(ca_miny), float(ca_minx)], [float(ca_maxy), float(ca_maxx)]]

# Left map style
de_areas_plot = de_areas.copy()
de_areas_plot["Total_Customers_num"] = pd.to_numeric(
    de_areas_plot.get("Total_Customers", 0), errors="coerce"
).fillna(0)
vmax = max(float(de_areas_plot["Total_Customers_num"].max()), 1.0)


def _left_style(feature):
    v = float(feature["properties"].get("Total_Customers_num", 0) or 0)
    frac = min(max(v / vmax, 0.0), 1.0)
    r = 255
    g = int(245 - 170 * frac)
    b = int(235 - 190 * frac)
    color = f"#{r:02x}{g:02x}{b:02x}"
    return {"fillColor": color, "color": "#9a1f00", "weight": 1.0, "fillOpacity": 0.55}


# Right map style
circuits_plot = de_circuits.copy()
circuits_plot["Circuit_Name"] = circuits_plot["Circuit_Name"].astype(str).fillna("Unknown")
unique_circuits = sorted(circuits_plot["Circuit_Name"].dropna().unique().tolist())

palette = [
    "#1f77b4", "#ff7f0e", "#2ca02c", "#d62728", "#9467bd",
    "#8c564b", "#e377c2", "#7f7f7f", "#bcbd22", "#17becf",
    "#393b79", "#637939", "#8c6d31", "#843c39", "#7b4173",
    "#3182bd", "#31a354", "#756bb1", "#636363", "#e6550d",
]
color_lookup = {name: palette[i % len(palette)] for i, name in enumerate(unique_circuits)}


def _right_style(feature):
    name = str(feature["properties"].get("Circuit_Name", "Unknown"))
    color = color_lookup.get(name, "#1f77b4")
    return {"fillColor": color, "color": color, "weight": 1.2, "fillOpacity": 0.35, "opacity": 0.8}


# Shared county layer
counties_plot = _json_safe_gdf(counties_ca[["NAME", "GEOID", "geometry"]])
county_json = counties_plot.to_json()
county_style = lambda _: {
    "fillColor": "#eef3e6",
    "fillOpacity": 0.20,
    "color": "#2a2a2a",
    "weight": 0.7,
    "opacity": 0.8,
}
county_tooltip = folium.GeoJsonTooltip(
    fields=["NAME", "GEOID"],
    aliases=["County", "FIPS"],
    labels=True,
    sticky=False,
)

# LEFT MAP
map_left = folium.Map(
    location=[center_lat, center_lon],
    zoom_start=6,
    tiles="CartoDB positron",
    control_scale=True,
    width="100%",
    height=650,
)


powergrid_plot = _json_safe_gdf(gdf_powergrid_CEC[["geometry"]].copy())
folium.GeoJson(
    data=powergrid_plot.to_json(),
    name="CEC physical grid",
    style_function=lambda _: {"color": "#4f4f4f", "weight": 1.1, "opacity": 0.65},
).add_to(map_left)

folium.GeoJson(
    data=_json_safe_gdf(
        de_areas_plot[
            ["Time_Place", "Circuit_Name", "County", "HFTD", "Total_Customers", "Total_Customers_num", "geometry"]
        ]
    ).to_json(),
    name="De-energized areas",
    style_function=_left_style,
    tooltip=folium.GeoJsonTooltip(
        fields=["Time_Place", "Circuit_Name", "County", "HFTD", "Total_Customers"],
        aliases=["Time Place", "Circuit(s)", "County", "HFTD", "Total Customers"],
        localize=True,
        sticky=False,
        labels=True,
    ),
).add_to(map_left)

folium.GeoJson(
    data=county_json,
    name="CA counties",
    style_function=county_style,
    tooltip=county_tooltip,
).add_to(map_left)

map_left.fit_bounds(ca_bounds)
folium.LayerControl(collapsed=False).add_to(map_left)

# # RIGHT MAP
# map_right = folium.Map(
#     location=[center_lat, center_lon],
#     zoom_start=6,
#     tiles="CartoDB positron",
#     control_scale=True,
#     width="100%",
#     height=650,
# )

# # powergrid_plot = _json_safe_gdf(gdf_powergrid_CEC[["geometry"]].copy())
# # folium.GeoJson(
# #     data=powergrid_plot.to_json(),
# #     name="CEC physical grid",
# #     style_function=lambda _: {"color": "#4f4f4f", "weight": 1.1, "opacity": 0.65},
# # ).add_to(map_right)

# folium.GeoJson(
#     data=_json_safe_gdf(
#         circuits_plot[["Circuit_Name", "County", "HFTD", "Total_Customers", "geometry"]]
#     ).to_json(),
#     name="De-energized circuits",
#     style_function=_right_style,
#     tooltip=folium.GeoJsonTooltip(
#         fields=["Circuit_Name", "County", "HFTD", "Total_Customers"],
#         aliases=["Circuit(s)", "County", "HFTD", "Total Customers"],
#         localize=True,
#         sticky=False,
#         labels=True,
#     ),
# ).add_to(map_right)

# folium.GeoJson(
#     data=county_json,
#     name="CA counties",
#     style_function=county_style,
#     tooltip=county_tooltip,
# ).add_to(map_right)

# map_right.fit_bounds(ca_bounds)
# folium.LayerControl(collapsed=False).add_to(map_right)

# print(
#     {
#         "deenergized_area_rows": int(len(de_areas_plot)),
#         "deenergized_circuit_features": int(len(circuits_plot)),
#         "cec_grid_features": int(len(gdf_powergrid_CEC)),
#         "ca_counties": int(len(counties_ca)),
#     }
# )

display(map_left)
# display(map_right)